# Lecture 4: Min-Hashing

## Overview

1. Using PyMinHash to find matches of strings.
2. A more detailed example to show the implementation of Min-Hashing


This example shows how to use PyMinHash to find matches of strings.

First, import Pandas and fix some settings.

In [1]:
%config Completer.use_jedi = False

import pandas as pd

pd.set_option('display.max_columns', 100)
pd.set_option('display.max_row', 500)
pd.set_option('display.max_colwidth', 200)

PyMinHash comes with a toy dataset containing various name and address combinations of Stoxx50 companies.

In [2]:
from pyminhash.datasets import load_data
df = load_data()
df.head()

,name
0,adidas ag adi dassler strasse 1 91074 germany
1,adidas ag adi dassler strasse 1 91074 herzogenaurach
2,adidas ag adi dassler strasse 1 91074 herzogenaurach germany
3,airbus se 2333 cs leiden netherlands
4,airbus se 2333 cs netherlands


We're going to match various representations that belong to the same company. For this, we import create a `MinHash` object and tell it to use 10 hash tables. More hash tables means more accurate Jaccard similarity calculation but also requires more time and memory.

In [3]:
from pyminhash.pyminhash import MinHash
myHasher = MinHash(n_hash_tables=10)

The `fit_predict` method needs the dataframe and the name of the column to which minhashing should be applied. The result is a dataframe containing all pairs that have a non-zero Jaccard similarity:

In [4]:
result = myHasher.fit_predict(df, 'name')
result.head()

,row_number_1,row_number_2,name_1,name_2,jaccard_sim
820,13,14,anheuser busch inbev sa nv brouwerijplein 1 3000 leuven belgium,anheuser busch inbev sa nv brouwerijplein 1 leuven belgium,1.0
1145,104,105,sanofi 54 rue la boetie 75008 france,sanofi 54 rue la boetie 75008 paris france,1.0
702,126,127,vinci sa 1 cours ferdinand de lesseps 92851 france,vinci sa 1 cours ferdinand de lesseps france,1.0
1422,79,80,koninklijke philips n v amstelplein 2 1096 bc,koninklijke philips n v amstelplein 2 1096 bc amsterdam,1.0
1419,77,78,koninklijke ahold delhaize n v provincialeweg 11,koninklijke ahold delhaize n v provincialeweg 11 netherlands,1.0


As one can see below, for a Jaccard similarity of 1.0, all words in the shortest string appear in the longest string. For lower Jaccard similarity values, the match is less than perfect. Note that Jaccard similarity has granularity of 1/n_hash_tables, in this example 0.1.

In [5]:
result.groupby('jaccard_sim').head(2)

,row_number_1,row_number_2,name_1,name_2,jaccard_sim
820,13,14,anheuser busch inbev sa nv brouwerijplein 1 3000 leuven belgium,anheuser busch inbev sa nv brouwerijplein 1 leuven belgium,1.0
1145,104,105,sanofi 54 rue la boetie 75008 france,sanofi 54 rue la boetie 75008 paris france,1.0
108,39,41,daimler ag 70372 stuttgart germany,daimler ag mercedesstrasse 120 70372 stuttgart germany,0.9
932,42,43,danone s a 15 rue du helder 75439 paris france,danone s a 15 rue du helder paris france,0.9
819,12,14,anheuser busch inbev sa nv 3000 leuven belgium,anheuser busch inbev sa nv brouwerijplein 1 leuven belgium,0.8
302,107,108,sap se 69190,sap se 69190 germany,0.8
750,127,128,vinci sa 1 cours ferdinand de lesseps france,vinci sa 1 cours ferdinand de lesseps rueil malmaison france,0.7
470,10,11,amadeus it group s a salvador de madariaga 1 28027 madrid,amadeus it group s a salvador de madariaga 1 28027 madrid spain,0.7
632,75,126,kering sa 40 rue de sevres 75007 paris france,vinci sa 1 cours ferdinand de lesseps 92851 france,0.6
940,56,57,engie sa 1 place samuel de champlain 92400 france,engie sa 92400 courbevoie france,0.6


# ======== runMinHashExample =======
This example code demonstrates comparing documents using the MinHash
approach. 

First, each document is represented by the set of shingles it contains. The
documents can then be compared using the Jaccard similarity of their 
shingle sets. This is computationally expensive, however, for large numbers
of documents. 

For comparison, we will also use the MinHash algorithm to calculate short 
signature vectors to represent the documents. These MinHash signatures can 
then be compared quickly by counting the number of components in which the 
signatures agree. We'll compare all possible pairs of documents, and find 
the pairs with high similarity.


The program follows these steps:
1. Convert each test file into a set of shingles.
   - The shingles are formed by combining three consecutive words together.
   - Shingles are mapped to shingle IDs using the CRC32 hash.
2. Calculate all Jaccard similarities directly.
   - This is ok for small dataset sizes. For the full 10,000 articles, it
     takes 20 minutes!
3. Calculate the MinHash signature for each document.
   - The MinHash algorithm is implemented using the random hash function 
     trick which prevents us from having to explicitly compute random
     permutations of all of the shingle IDs. For further explanation, see
     section 3.3.5 of http://infolab.stanford.edu/~ullman/mmds/ch3.pdf
4. Compare all MinHash signatures to one another.
   - Compare MinHash signatures by counting the number of components in which
     the signatures are equal. Divide the number of matching components by
     the signature length to get a similarity value.
   - Display pairs of documents / signatures with similarity greater than a
     threshold.

In [6]:
from __future__ import division
import os
import re
import random
import time
import binascii
from bisect import bisect_right
from heapq import heappop, heappush
import sys

# This is the number of components in the resulting MinHash signatures.
# Correspondingly, it is also the number of random hash functions that
# we will need in order to calculate the MinHash.
numHashes = 10;

# You can run this code for different portions of the dataset.
# It ships with data set sizes 100, 1000, 2500, and 10000.
numDocs = 1000
dataFile = "./data/articles_" + str(numDocs) + ".train"
truthFile = "./data/articles_" + str(numDocs) + ".truth" #读取文件（numDocs可改）

In [7]:
# =============================================================================
#                  Parse The Ground Truth Tables
# =============================================================================
# Build a dictionary mapping the document IDs to their plagiaries, and vice-
# versa.
plagiaries = {} # 先建立字典，之后将truth中的内容建立起映射字典

# Open the truth file.
f = open(truthFile, "r")

# For each line of the files...
for line in f:
  
  # Strip the newline character, if present.
  if line[-1] == '\n':
      line = line[0:-1]
      
  docs = line.split(" ")

  # Map the two documents to each other.
  plagiaries[docs[0]] = docs[1]
  plagiaries[docs[1]] = docs[0]

plagiaries 

{'t1088': 't5015',
 't5015': 't1088',
 't1297': 't4638',
 't4638': 't1297',
 't1768': 't5248',
 't5248': 't1768',
 't1952': 't3495',
 't3495': 't1952',
 't980': 't2023',
 't2023': 't980',
 't2535': 't8642',
 't8642': 't2535',
 't2839': 't9303',
 't9303': 't2839',
 't2957': 't7111',
 't7111': 't2957',
 't3268': 't7998',
 't7998': 't3268',
 't3466': 't7563',
 't7563': 't3466'}

In [8]:
# =============================================================================
#               Convert Documents To Sets of Shingles
# =============================================================================

print ("Shingling articles...")

# The current shingle ID value to assign to the next new shingle we 
# encounter. When a shingle gets added to the dictionary, we'll increment this
# value.
curShingleID = 0

# Create a dictionary of the articles, mapping the article identifier (e.g., 
# "t8470") to the list of shingle IDs that appear in the document.
docsAsShingleSets = {};
  
# Open the data file.
f = open(dataFile, "r")

docNames = []

t0 = time.time()

totalShingles = 0

for i in range(0, numDocs):
  
  # Read all of the words (they are all on one line) and split them by white
  # space.
  words = f.readline().split(" ") 
  
  # Retrieve the article ID, which is the first word on the line.  
  docID = words[0]
  
  # Maintain a list of all document IDs.  
  docNames.append(docID)
    
  del words[0]  
  
  # 'shinglesInDoc' will hold all of the unique shingle IDs present in the 
  # current document. If a shingle ID occurs multiple times in the document,
  # it will only appear once in the set (this is a property of Python sets).
  shinglesInDoc = set()
  
  # For each word in the document...
  for index in range(0, len(words) - 2):
    # Construct the shingle text by combining three words together.
    shingle = words[index] + " " + words[index + 1] + " " + words[index + 2]
    print(shingle)
    # Hash the shingle to a 32-bit integer.
    arc = binascii.crc32(str.encode(shingle)) & 0xffffffff #把每个shingle encoder为32位整型
    print(arc)
    # Add the hash value to the list of shingles for the current document. 
    # Note that set objects will only add the value to the set if the set 
    # doesn't already contain it. 
    shinglesInDoc.add(arc)
  
  # Store the completed list of shingles for this document in the dictionary.
  # print(shinglesInDoc)
  docsAsShingleSets[docID] = shinglesInDoc
  
  # Count the number of shingles across all documents.
  totalShingles = totalShingles + (len(words) - 2)

# Close the data file.  
f.close()  

# Report how long shingling took.

print ('\nShingling ' + str(numDocs) + ' docs took %.2f sec.' % (time.time() - t0))
 
print ('\nAverage shingles per doc: %.2f' % (totalShingles / numDocs))


Shingling articles...
The Supreme Court
3846031197
Supreme Court in
1452056475
Court in Johnnesberg
2001668326
in Johnnesberg on
916407977
Johnnesberg on Friday
3524098189
on Friday postponed
1522497869
Friday postponed until
2352577345
postponed until March
2439121341
until March 14
680156507
March 14 a
1985983683
14 a hearing
2071173127
a hearing on
585542980
hearing on a
3663235619
on a petition
1202176175
a petition by
3728696948
petition by government
2245659702
by government minister
3968053362
government minister Winnie
4269249448
minister Winnie Mandela
674227162
Winnie Mandela to
2749817072
Mandela to prevent
1889735404
to prevent police
1726676494
prevent police reading
2431742974
police reading documents
612012711
reading documents seized
1075343205
documents seized from
1777332463
seized from her
1106062239
from her home,
1382442749
her home, the
961103843
home, the SAPA
493459006
the SAPA news
2178323770
SAPA news agency
2898647969
news agency reported.
1255302733
agency r

In [9]:
# =============================================================================
#                     Define Triangle Matrices
# =============================================================================

# Define virtual Triangle matrices to hold the similarity values. For storing
# similarities between pairs, we only need roughly half the elements of a full
# matrix. Using a triangle matrix requires less than half the memory of a full
# matrix, and can protect the programmer from inadvertently accessing one of
# the empty/invalid cells of a full matrix.

# Calculate the number of elements needed in our triangle matrix

#定义一个空的上三角矩阵来存储相似度值
numElems = int(numDocs * (numDocs - 1) / 2)

# Initialize two empty lists to store the similarity values. 
# 'JSim' will be for the actual Jaccard Similarity values. 
# 'estJSim' will be for the estimated Jaccard Similarities found by comparing
# the MinHash signatures.
JSim = [0 for x in range(numElems)]
estJSim = [0 for x in range(numElems)]

# Define a function to map a 2D matrix coordinate into a 1D index.
def getTriangleIndex(i, j):
  # If i == j that's an error.
  if i == j:
    sys.stderr.write("Can't access triangle matrix with i == j")
    sys.exit(1)
  # If j < i just swap the values.
  if j < i:
    temp = i
    i = j
    j = temp
  
  # Calculate the index within the triangular array.
  # This fancy indexing scheme is taken from pg. 211 of:
  # http://infolab.stanford.edu/~ullman/mmds/ch6.pdf
  # But I adapted it for a 0-based index.
  # Note: The division by two should not truncate, it
  #       needs to be a float. 
  k = int(i * (numDocs - (i + 1) / 2.0) + j - i) - 1
  
  return k

In [10]:
# =============================================================================
#                 Calculate Jaccard Similarities
# =============================================================================
# In this section, we will directly calculate the Jaccard similarities by 
# comparing the sets. This is included here to show how much slower it is than
# the MinHash approach.

# Calculating the Jaccard similarities gets really slow for large numbers
# of documents.
if numDocs <= 2500:
#if True:
    print("\nCalculating Jaccard Similarities...")

    # Time the calculation.
    t0 = time.time()

    # For every document pair...
    for i in range(0, numDocs):
      
      # Print progress every 100 documents.
      if (i % 100) == 0:
        print("  (" + str(i) + " / " + str(numDocs) + ")")

      # Retrieve the set of shingles for document i.
      s1 = docsAsShingleSets[docNames[i]]
      
      for j in range(i + 1, numDocs):
        # Retrieve the set of shingles for document j.
        s2 = docsAsShingleSets[docNames[j]]
        
        # Calculate and store the actual Jaccard similarity.
        JSim[getTriangleIndex(i, j)] = (len(s1.intersection(s2)) / len(s1.union(s2)))    

    # Calculate the elapsed time (in seconds)
    elapsed = (time.time() - t0)
        
    print("\nCalculating all Jaccard Similarities took %.2fsec" % elapsed)

# Delete the Jaccard Similarities, since it's a pretty big matrix.    
del JSim


Calculating Jaccard Similarities...
  (0 / 1000)
  (100 / 1000)
  (200 / 1000)
  (300 / 1000)
  (400 / 1000)
  (500 / 1000)
  (600 / 1000)
  (700 / 1000)
  (800 / 1000)
  (900 / 1000)

Calculating all Jaccard Similarities took 6.98sec


In [11]:
# =============================================================================
#                 Generate MinHash Signatures
# =============================================================================

# Time this step.
t0 = time.time()

print('\nGenerating random hash functions...')

# Record the maximum shingle ID that we assigned.
maxShingleID = 2**32-1

# We need the next largest prime number above 'maxShingleID'.
nextPrime = 4294967311


# Our random hash function will take the form of:
#   h(x) = (a*x + b) % c
# Where 'x' is the input value, 'a' and 'b' are random coefficients, and 'c' is
# a prime number just greater than maxShingleID.

# Generate a list of 'k' random coefficients for the random hash functions,
# while ensuring that the same value does not appear multiple times in the 
# list.
def pickRandomCoeffs(k):
  # Create a list of 'k' random values.
  randList = []
  
  while k > 0:
    # Get a random shingle ID.
    randIndex = random.randint(0, maxShingleID) 
  
    # Ensure that each random number is unique.
    while randIndex in randList:
      randIndex = random.randint(0, maxShingleID) 
    
    # Add the random number to the list.
    randList.append(randIndex)
    k = k - 1
    
  return randList

# For each of the 'numHashes' hash functions, generate a different coefficient 'a' and 'b'.   
coeffA = pickRandomCoeffs(numHashes)
coeffB = pickRandomCoeffs(numHashes)

print('\nGenerating MinHash signatures for all documents...')

# List of documents represented as signature vectors
signatures = []

# Rather than generating a random permutation of all possible shingles, 
# we'll just hash the IDs of the shingles that are *actually in the document*,
# then take the lowest resulting hash code value. This corresponds to the index 
# of the first shingle that you would have encountered in the random order.

# For each document...
for docID in docNames:
  
  # Get the shingle set for this document.
  shingleIDSet = docsAsShingleSets[docID]
  
  # The resulting minhash signature for this document. 
  signature = []
  
  # For each of the random hash functions...
  for i in range(0, numHashes):
    
    # For each of the shingles actually in the document, calculate its hash code
    # using hash function 'i'. 
    
    # Track the lowest hash ID seen. Initialize 'minHashCode' to be greater than
    # the maximum possible value output by the hash.
    minHashCode = nextPrime + 1
    
    # For each shingle in the document...
    for shingleID in shingleIDSet:
      # Evaluate the hash function.
      hashCode = (coeffA[i] * shingleID + coeffB[i]) % nextPrime 
      
      # Track the lowest hash code seen.
      if hashCode < minHashCode:
        minHashCode = hashCode

    # Add the smallest hash code value as component number 'i' of the signature.
    signature.append(minHashCode)
  
  # Store the MinHash signature for this document.
  signatures.append(signature)

# Calculate the elapsed time (in seconds)
elapsed = (time.time() - t0)
        
print("\nGenerating MinHash signatures took %.2fsec" % elapsed)


Generating random hash functions...

Generating MinHash signatures for all documents...

Generating MinHash signatures took 0.74sec


In [12]:
# =============================================================================
#                     Compare All Signatures
# =============================================================================  

print('\nComparing all signatures...')
  
# Creates a N x N matrix initialized to 0.

# Time this step.
t0 = time.time()

# For each of the test documents...
for i in range(0, numDocs):
  # Get the MinHash signature for document i.
  signature1 = signatures[i]
    
  # For each of the other test documents...
  for j in range(i + 1, numDocs):
    
    # Get the MinHash signature for document j.
    signature2 = signatures[j]
    
    count = 0
    # Count the number of positions in the minhash signature which are equal.
    for k in range(0, numHashes):
      count = count + (signature1[k] == signature2[k])
    
    # Record the percentage of positions which matched.    
    estJSim[getTriangleIndex(i, j)] = (count / numHashes)

# Calculate the elapsed time (in seconds)
elapsed = (time.time() - t0)
        
print("\nComparing MinHash signatures took %.2fsec" % elapsed)


Comparing all signatures...

Comparing MinHash signatures took 0.89sec


In [14]:
# =============================================================================
#                   Display Similar Document Pairs
# =============================================================================  

# Count the true positives and false positives.
tp = 0
fp = 0
  
threshold = 0.5  
print ("\nList of Document Pairs with J(d1,d2) more than", threshold)
print ("Values shown are the estimated Jaccard similarity and the actual")
print ("Jaccard similarity.\n")
print ("                   Est. J   Act. J")

# For each of the document pairs...
for i in range(0, numDocs):  
  for j in range(i + 1, numDocs):
    # Retrieve the estimated similarity value for this pair.
    estJ = estJSim[getTriangleIndex(i, j)]
    
    # If the similarity is above the threshold...
    if estJ > threshold:
    
      # Calculate the actual Jaccard similarity for validation.
      s1 = docsAsShingleSets[docNames[i]]
      s2 = docsAsShingleSets[docNames[j]]
      J = (len(s1.intersection(s2)) / len(s1.union(s2)))
      
      # Print out the match and similarity values with pretty spacing.
      print ("  %5s --> %5s   %.2f     %.2f" % (docNames[i], docNames[j], estJ, J))
      
      # Check whether this is a true positive or false positive.
      # We don't need to worry about counting the same true positive twice
      # because we implemented the for-loops to only compare each pair once.
      if plagiaries[docNames[i]] == docNames[j]:
        tp = tp + 1
      else:
        fp = fp + 1

# Display true positive and false positive counts.
print ("True positives:  " + str(tp) + " / " + str(int(len(plagiaries.keys()) / 2)))
print ("False positives: " + str(fp))


List of Document Pairs with J(d1,d2) more than 0.5
Values shown are the estimated Jaccard similarity and the actual
Jaccard similarity.

                   Est. J   Act. J
   t980 --> t2023   1.00     0.98
  t1088 --> t5015   1.00     0.98
  t1297 --> t4638   1.00     0.98
  t1768 --> t5248   0.90     0.98
  t1952 --> t3495   1.00     0.98
  t2535 --> t8642   1.00     0.98
  t2839 --> t9303   1.00     0.98
  t2957 --> t7111   1.00     0.98
  t3268 --> t7998   1.00     0.98
  t3466 --> t7563   0.90     0.98
  t7065 --> t7066   0.60     0.08


KeyError: 't7065'